In [1]:
# This Python 3 environment comes with many helpful analytics libraries installed
# It is defined by the kaggle/python Docker image: https://github.com/kaggle/docker-python
# For example, here's several helpful packages to load

import numpy as np # linear algebra
import pandas as pd # data processing, CSV file I/O (e.g. pd.read_csv)

# Input data files are available in the read-only "../input/" directory
# For example, running this (by clicking run or pressing Shift+Enter) will list all files under the input directory

import os
for dirname, _, filenames in os.walk('/kaggle/input'):
    for filename in filenames:
        print(os.path.join(dirname, filename))

# You can write up to 20GB to the current directory (/kaggle/working/) that gets preserved as output when you create a version using "Save & Run All" 
# You can also write temporary files to /kaggle/temp/, but they won't be saved outside of the current session

/kaggle/input/pm-84978842-at-06-13-2025-02-04-38/__script__.py
/kaggle/input/pm-84978842-at-06-13-2025-02-04-38/mako-1.3.10-py3-none-any.whl
/kaggle/input/pm-84978842-at-06-13-2025-02-04-38/charset_normalizer-3.4.2-cp311-cp311-manylinux_2_17_x86_64.manylinux2014_x86_64.whl
/kaggle/input/pm-84978842-at-06-13-2025-02-04-38/hf_xet-1.1.3-cp37-abi3-manylinux_2_17_x86_64.manylinux2014_x86_64.whl
/kaggle/input/pm-84978842-at-06-13-2025-02-04-38/nvidia_nvjitlink_cu12-12.6.85-py3-none-manylinux2010_x86_64.manylinux_2_12_x86_64.whl
/kaggle/input/pm-84978842-at-06-13-2025-02-04-38/urllib3-2.4.0-py3-none-any.whl
/kaggle/input/pm-84978842-at-06-13-2025-02-04-38/joblib-1.5.1-py3-none-any.whl
/kaggle/input/pm-84978842-at-06-13-2025-02-04-38/certifi-2025.4.26-py3-none-any.whl
/kaggle/input/pm-84978842-at-06-13-2025-02-04-38/filelock-3.18.0-py3-none-any.whl
/kaggle/input/pm-84978842-at-06-13-2025-02-04-38/scipy-1.15.3-cp311-cp311-manylinux_2_17_x86_64.manylinux2014_x86_64.whl
/kaggle/input/pm-84978842-

In [2]:
import pandas as pd
from sklearn.model_selection import train_test_split

csv_path = '/kaggle/input/open-polymer-challenge/train.csv'
train_df = pd.read_csv(csv_path)

# 1. split off 20% for dev_test
temp_df, dev_test = train_test_split(
    train_df,
    test_size=0.2,
    random_state=42,  # for reproducibility
    shuffle=True
)

# 2. split the remaining 80% into 75% train / 25% valid → 0.6 / 0.2 overall
dev_train, dev_val = train_test_split(
    temp_df,
    test_size=0.25,  # 0.25 * 0.8 = 0.2 of the original
    random_state=42,
    shuffle=True
)

# Verify sizes
print(f"Total rows:   {len(train_df)}")
print(f"Dev train:    {len(dev_train)} ({len(dev_train)/len(train_df):.2%})")
print(f"Dev valid:    {len(dev_val)} ({len(dev_val)/len(train_df):.2%})")
print(f"Dev test:     {len(dev_test)} ({len(dev_test)/len(train_df):.2%})")
print(f"Polymer example:{dev_train['SMILES'].to_list()[:3]}")
print(f"Columns:{dev_train.columns}")

Total rows:   7973
Dev train:    4783 (59.99%)
Dev valid:    1595 (20.01%)
Dev test:     1595 (20.01%)
Polymer example:['*Nc1ccc(CC(CC(C)(C)c2ccc(N*)cc2)=C(C)C)cc1', '*CC(*)(CC(=O)OC)C(=O)OC12CC3CC(C)(CC(C)(C3)C1)C2', '*OP(=O)(Oc1c(Cl)cc(Cl)cc1Cl)Oc1c(Cl)c(Cl)c(*)c(Cl)c1Cl']
Columns:Index(['id', 'SMILES', 'Tg', 'FFV', 'Tc', 'Density', 'Rg'], dtype='object')


In [ ]:
import numpy as np
from sklearn.metrics import mean_squared_error

X_train = dev_train['SMILES'].to_list()
y_train = dev_train[['Tg', 'FFV', 'Tc', 'Density', 'Rg']].to_numpy()
X_val   = dev_val['SMILES'].to_list()
y_val   = dev_val[['Tg', 'FFV', 'Tc', 'Density', 'Rg']].to_numpy()
X_test  = dev_test['SMILES'].to_list()
y_test  = dev_test[['Tg', 'FFV', 'Tc', 'Density', 'Rg']].to_numpy()
task_names = ['Tg', 'FFV', 'Tc', 'Density', 'Rg']

def compute_mse(y_true, y_pred):
    print("MSE per task:")
    for i, name in enumerate(task_names):
        mask = ~np.isnan(y_true[:, i])
        if mask.sum() > 0:
            mse = mean_squared_error(y_true[mask, i], y_pred[mask, i])
            print(f"  {name}: {mse:.4f}")
        else:
            print(f"  {name}: N/A")
    mask_all = ~np.isnan(y_true)
    overall = mean_squared_error(y_true[mask_all], y_pred[mask_all])
    print(f"Overall MSE: {overall:.4f}")


In [ ]:
from tqdm.notebook import tqdm as notebook_tqdm
import tqdm
tqdm.tqdm = notebook_tqdm
tqdm.trange = notebook_tqdm

from torch_molecule import LSTMMolecularPredictor
from torch_molecule.utils.search import ParameterType, ParameterSpec

search_parameters = {
    "output_dim": ParameterSpec(ParameterType.INTEGER, (8, 32)),
    "LSTMunits": ParameterSpec(ParameterType.INTEGER, (30, 120)),
    "learning_rate": ParameterSpec(ParameterType.LOG_FLOAT, (1e-4, 1e-2)),
}

lstm = LSTMMolecularPredictor(
    task_type="regression",
    num_task=5,
    batch_size=192,
    epochs=200,
    verbose=True
)

print("Model initialized successfully")
lstm.autofit(
    X_train=X_train,
    y_train=y_train,
    X_val=X_val,
    y_val=y_val,
    search_parameters=search_parameters,
    n_trials=10
)


In [ ]:
y_predict = lstm.predict(X_test)['prediction']
compute_mse(y_test, y_predict)


In [ ]:
from rdkit import Chem
from rdkit.Chem import rdFingerprintGenerator
from sklearn.ensemble import RandomForestRegressor

morgan_gen = rdFingerprintGenerator.GetMorganGenerator(radius=2, fpSize=1024)

def smiles_to_fp(smiles):
    mol = Chem.MolFromSmiles(smiles)
    if mol is None:
        return np.zeros(1024, dtype=np.uint8)
    return morgan_gen.GetFingerprintAsNumPy(mol)

X_train_feats = np.vstack([smiles_to_fp(s) for s in X_train])
X_val_feats   = np.vstack([smiles_to_fp(s) for s in X_val])
X_test_feats  = np.vstack([smiles_to_fp(s) for s in X_test])

X_dev_feats = np.vstack([X_train_feats, X_val_feats])
y_dev = np.vstack([y_train, y_val])

models = {}
y_pred = np.zeros_like(y_test)

for idx, name in enumerate(task_names):
    print('Training random forest for:', name)
    y_col = y_dev[:, idx]
    mask  = ~np.isnan(y_col)
    rf = RandomForestRegressor(n_estimators=100, random_state=42)
    rf.fit(X_dev_feats[mask], y_col[mask])
    models[name] = rf
    y_pred[:, idx] = rf.predict(X_test_feats)

compute_mse(y_test, y_pred)


In [ ]:
from torch_molecule import GNNMolecularPredictor
from torch_molecule.utils.search import ParameterType, ParameterSpec

search_parameters = {
    'num_layer': ParameterSpec(param_type=ParameterType.INTEGER, value_range=(2, 5)),
    'hidden_size': ParameterSpec(param_type=ParameterType.INTEGER, value_range=(64, 512)),
    'learning_rate': ParameterSpec(param_type=ParameterType.LOG_FLOAT, value_range=(1e-4, 1e-2)),
}

gnn = GNNMolecularPredictor(
    task_type="regression",
    num_task=5,
    batch_size=192,
    epochs=200,
    verbose=True
)

print("Model initialized successfully")
gnn.autofit(
    X_train=X_train,
    y_train=y_train,
    X_val=X_val,
    y_val=y_val,
    search_parameters=search_parameters,
    n_trials=10
)


In [ ]:
y_predict = gnn.predict(X_test)['prediction']
compute_mse(y_test, y_predict)


In [ ]:
import pandas as pd

sample_sub = pd.read_csv('/kaggle/input/open-polymer-challenge/sample_submission.csv')
print(sample_sub.head())

test_df = pd.read_csv('/kaggle/input/open-polymer-challenge/test.csv')
print(test_df.head())

X_final = test_df['SMILES'].to_list()

lstm_preds = lstm.predict(X_final)['prediction']
gnn_preds  = gnn.predict(X_final)['prediction']
preds = (lstm_preds + gnn_preds) / 2

# build from test_df so predictions stay aligned with their ids
submission_df = pd.DataFrame(preds, columns=task_names)
submission_df.insert(0, 'id', test_df['id'].values)
submission_df = submission_df[sample_sub.columns]
print('submission_df', submission_df)


In [9]:
# save to CSV
submission_df.to_csv('submission.csv', index=False)